# RL Gemma 4 Text + Unsloth + Verifiers + OpenFARM EnvGroup

This notebook demonstrates OpenFARM as a Prime/Verifiers-native training lab: Gemma 4 is trained with GRPO through Unsloth, while rewards come from OpenFARM Verifiers environments installed from the Prime environment hub.

The default run trains on a small multi-task text EnvGroup:

- `openfarm-aww`: adversarial animal-welfare reasoning from text descriptions.
- `openfarm-dog-pain-triage`: canine clinical text pain-state triage.
- **DISABLED** `openfarm-bioacustics` in `modality="text"`: acoustic metadata classification for pig/ungulate vocalization tasks.

In [1]:
%%capture
#@title Installation
import os, importlib.util
!pip install --upgrade -qqq uv

if importlib.util.find_spec("torch") is None or "COLAB_" in "".join(os.environ.keys()):
    try:
        import numpy, PIL
        _numpy = f"numpy=={numpy.__version__}"
        _pil = f"pillow=={PIL.__version__}"
    except Exception:
        _numpy = "numpy"
        _pil = "pillow"

    # Gemma 4 requires transformers >= 5.5.0; do not pin transformers to 4.x.
    !uv pip install -qqq         "torch>=2.8.0" "triton>=3.4.0" {_numpy} {_pil} torchvision bitsandbytes         "unsloth_zoo[base] @ git+https://github.com/unslothai/unsloth-zoo"         "unsloth[base] @ git+https://github.com/unslothai/unsloth"         git+https://github.com/triton-lang/triton.git@0add68262ab0a2e33b84524346cb27cbb2787356#subdirectory=python/triton_kernels
elif importlib.util.find_spec("unsloth") is None:
    !uv pip install -qqq unsloth

!uv pip install --upgrade --no-deps "transformers>=5.5.0" "tokenizers>=0.22.0,<=0.23.0" "trl>=0.28.0" unsloth unsloth_zoo
!uv pip install -qqq prime verifiers hatchling "datasets==4.3.0" "huggingface_hub>=0.34.0" hf_transfer wandb protobuf

## Configuration

The defaults are intentionally small enough for a Colab/Kaggle demonstration. Increase row limits and `max_steps` for a real run.

In [2]:
#@title Model and run config
model_id = "unsloth/gemma-4-E2B-it" #@param ["unsloth/gemma-4-E2B-it", "unsloth/gemma-4-E4B-it"] {allow-input: true}
max_seq_length = 4096 #@param {type:"integer"}
lora_rank = 32 #@param {type:"integer"}
load_in_4bit = False #@param {type:"boolean"}
use_wandb = True #@param {type:"boolean"}
wandb_project = "openfarm-gemma4-unsloth-rl" #@param {type:"string"}
seed = 3301 #@param {type:"integer"}

#@title OpenFARM EnvGroup config
team_id = "openfarm" #@param {type:"string"}
# use_native_thinking = True #@param {type:"boolean"}
require_explanation = True #@param {type:"boolean"}
format_reward_weight = 0.2 #@param {type:"number"}
include_aww_adversarial_context = True #@param {type:"boolean"}

max_aww_examples = 160 #@param {type:"integer"}
max_dog_examples = -1 #@param {type:"integer"}
max_bio_examples_per_task = 96 #@param {type:"integer"}
max_total_train_rows = 1024 #@param {type:"integer"}
max_total_eval_rows = 128 #@param {type:"integer"}
run_eval_before_training = True #@param {type:"boolean"}
run_eval_after_training = True #@param {type:"boolean"}
eval_steps_fraction = 0.25 #@param {type:"number"}


#@markdown ⚠️ **WARNING:** Disabled tasks are highly unstable/difficult for this model on text-only mode. Enable with caution.
include_dog_pain = True #@param {type:"boolean"}
include_soundwel_call_type = False #@param {type:"boolean"}
include_soundwel_valence = False #@param {type:"boolean"}
include_ungulate_valence = False #@param {type:"boolean"}
include_hen_stress_binary = False #@param {type:"boolean"}
include_catmeows_context = False #@param {type:"boolean"}

In [3]:
#@title Load Gemma 4 with Unsloth. **At this point you might be prompted to restart the notebook**
from unsloth import FastVisionModel
import torch
import functools

model, tokenizer = FastVisionModel.from_pretrained(
    model_name = model_id,
    max_seq_length = max_seq_length,
    load_in_4bit = load_in_4bit,
    fast_inference = False,
)

model = FastVisionModel.get_peft_model(
    model,
    r = lora_rank,
    target_modules = [
        "q_proj", "k_proj", "v_proj", "o_proj",
        "gate_proj", "up_proj", "down_proj",
    ],
    lora_alpha = lora_rank * 2,
    use_gradient_checkpointing = "unsloth",
    random_state = seed,
)

#     # Hugging Face transformers takes template variables directly as kwargs!

if use_wandb:
    import os
    import wandb
    os.environ["WANDB_PROJECT"] = wandb_project

🦥 Unsloth: Will patch your computer to enable 2x faster free finetuning.
🦥 Unsloth Zoo will now patch everything to make training faster!
==((====))==  Unsloth 2026.5.3: Fast Gemma4 patching. Transformers: 5.8.1.
   \\   /|    Tesla T4. Num GPUs = 1. Max memory: 14.563 GB. Platform: Linux.
O^O/ \_/ \    Torch: 2.10.0+cu128. CUDA: 7.5. CUDA Toolkit: 12.8. Triton: 3.6.0
\        /    Bfloat16 = FALSE. FA [Xformers = None. FA2 = False]
 "-____-"     Free license: http://github.com/unslothai/unsloth
Unsloth: Fast downloading is enabled - ignore downloading bars which are red colored!
Unsloth: QLoRA and full finetuning all not selected. Switching to 16bit LoRA.


Loading weights:   0%|          | 0/1951 [00:00<?, ?it/s]

## Build the OpenFARM EnvGroup

Each child environment is installed from the Prime environment hub, loaded with text-compatible args, and wrapped into one `vf.EnvGroup`. Verifiers stores EnvGroup routing under `info["env_id"]`; the reward bridge below preserves that route instead of using legacy plain-string task routes.

In [4]:
#@title Install and load OpenFARM environments
import json
import subprocess
from collections import Counter

import verifiers as vf
import verifiers.envs.env_group

# Force Verifiers to always use lists for routing keys to prevent Arrow schema clashes
verifiers.envs.env_group._route_value = lambda route: list(route) if route else None

def hub_env(name: str) -> str:
    return f"{team_id}/{name}" if team_id else name


env_specs = [
    {
        "name": "aww",
        "env_id": hub_env("openfarm-aww"),
        "args": {
            "max_examples": max_aww_examples,
            "require_explanation": require_explanation,
            "judge_mode": "none",
            "format_reward_weight": format_reward_weight,
            "include_adversarial_context": include_aww_adversarial_context,
        },
    },
]

if include_dog_pain:
    env_specs.append({
        "name": "dog_pain",
        "env_id": hub_env("openfarm-dog-pain-triage"),
        "args": {
            "max_examples": max_dog_examples,
            "require_explanation": require_explanation,
            "judge_mode": "none",
            "format_reward_weight": format_reward_weight,
        },
    })

bio_tasks = []
if include_soundwel_valence:
    bio_tasks.append(("bio_soundwel_valence", "soundwel_valence"))
if include_soundwel_call_type:
    bio_tasks.append(("bio_soundwel_call_type", "soundwel_call_type"))
if include_ungulate_valence:
    bio_tasks.append(("bio_ungulate_valence", "ungulate_valence"))
if include_hen_stress_binary:
    bio_tasks.append(("bio_hen_stress_binary", "laying_hen_stress_binary"))
if include_catmeows_context:
    bio_tasks.append(("bio_catmeows_context", "catmeows_context"))

for name, task in bio_tasks:
    env_specs.append({
        "name": name,
        "env_id": hub_env("openfarm-bioacustics"),
        "args": {
            "task": task,
            "modality": "text",
            "max_examples_per_task": max_bio_examples_per_task,
            "balancing_strategy": "balanced",
            "require_explanation": require_explanation,
            "format_reward_weight": format_reward_weight,
        },
    })

print("EnvGroup children:")
for spec in env_specs:
    print("-", spec["name"], spec["env_id"], spec["args"])
    subprocess.run(["prime", "env", "install", spec["env_id"]], check=True)

envs = [vf.load_environment(spec["env_id"], **spec["args"]) for spec in env_specs]
vf_env = vf.EnvGroup(envs=envs, env_names=[spec["name"] for spec in env_specs])

train_dataset = vf_env.get_dataset()
keep_cols = ["prompt", "answer", "example_id", "info"]
train_dataset = train_dataset.select_columns([c for c in keep_cols if c in train_dataset.column_names])
train_dataset = train_dataset.shuffle(seed=seed)
if max_total_train_rows > 0:
    train_dataset = train_dataset.select(range(min(max_total_train_rows, len(train_dataset))))

eval_dataset = vf_env.get_eval_dataset()
eval_dataset = eval_dataset.select_columns([c for c in keep_cols if c in eval_dataset.column_names])
eval_dataset = eval_dataset.shuffle(seed=seed + 1)
if max_total_eval_rows > 0:
    eval_dataset = eval_dataset.select(range(min(max_total_eval_rows, len(eval_dataset))))


def route_name(info):
    if isinstance(info, str):
        info = json.loads(info)
    route = info.get("env_id", "unknown") if isinstance(info, dict) else "unknown"
    if isinstance(route, list):
        return "/".join(route)
    return str(route)

print("Train rows:", len(train_dataset))
print("Train route counts:", Counter(route_name(row["info"]) for row in train_dataset))
print("Eval rows:", len(eval_dataset))
print("Eval route counts:", Counter(route_name(row["info"]) for row in eval_dataset))
print("Sample prompt:")
print(train_dataset[0]["prompt"])
print("Sample answer:", train_dataset[0]["answer"])
print("Sample info:", train_dataset[0]["info"])

EnvGroup children:
- aww openfarm/openfarm-aww {'max_examples': 160, 'require_explanation': True, 'judge_mode': 'none', 'format_reward_weight': 0.2, 'include_adversarial_context': True}
- dog_pain openfarm/openfarm-dog-pain-triage {'max_examples': -1, 'require_explanation': True, 'judge_mode': 'none', 'format_reward_weight': 0.2}


Map:   0%|          | 0/160 [00:00<?, ? examples/s]

Map:   0%|          | 0/160 [00:00<?, ? examples/s]

Map:   0%|          | 0/48 [00:00<?, ? examples/s]

Map:   0%|          | 0/48 [00:00<?, ? examples/s]

...

Map:   0%|          | 0/18 [00:00<?, ? examples/s]

Map:   0%|          | 0/18 [00:00<?, ? examples/s]

Map:   0%|          | 0/228 [00:00<?, ? examples/s]

Map:   0%|          | 0/66 [00:00<?, ? examples/s]

Train rows: 228
Route counts: Counter({'aww': 160, 'dog_pain': 68})
Sample prompt:
[{'role': 'system', 'content': 'You are an expert veterinary AI.'}, {'role': 'user', 'content': "[SPECIES CLASS]\nSeal\n\n[SUBJECT]\nCanine (Dog)\n\n[CONTEXT]\nBehavioral observation enclosure, human evaluator approaching the front fencing.\n\n[VISUAL CUES]\nThe dog maintains direct visual contact with the evaluator, standing with relaxed body posture. The dog's inner brow (AU101) is noticeably raised, giving the animal a wide-eyed, child-like appearance.\n\n[FARM MANAGER ASSESSMENT/EXTERNAL CONTEXT]\nIn many broad mammalian scales (like the Cow Pain Scale), a raised inner brow is biologically validated as an indicator of an animal experiencing physical pain.\n\n[TASK]\nBased on the visual cues and context provided, analyze the animal's affective state. Reason through any potential biological confounders or distractor information. Provide your final classification as exactly one of the following:\n- Nega

## Train

In [5]:
#@title Verifiers -> TRL reward bridge
import asyncio
import json
import time
from collections import defaultdict

import nest_asyncio
import wandb
from transformers import TrainerCallback

from verifiers.utils.message_utils import normalize_messages
from verifiers.utils.thread_utils import get_or_create_thread_loop
from verifiers.utils.usage_utils import StateUsageTracker

nest_asyncio.apply()
env_metrics_buffer = defaultdict(list)


class VerifiersMetricsCallback(TrainerCallback):
    def on_train_begin(self, args, state, control, **kwargs):
        if wandb.run is not None:
            wandb.define_metric("train/env_metrics/*", step_metric="train/global_step")
            wandb.define_metric("train/rewards/*", step_metric="train/global_step")
            wandb.define_metric("eval/env_metrics/*", step_metric="train/global_step")
            wandb.define_metric("eval/rewards/*", step_metric="train/global_step")

    def on_log(self, args, state, control, logs=None, **kwargs):
        if not env_metrics_buffer or logs is None:
            return
        for k, v in env_metrics_buffer.items():
            logs[k] = sum(v) / len(v)
        env_metrics_buffer.clear()


def _maybe_json(value):
    return json.loads(value) if isinstance(value, str) else value


def build_trl_reward_funcs(vf_env, model):
    # Return a TRL reward function backed by Verifiers' rubric engine.
    def extract_text(completion) -> str:
        if isinstance(completion, list):
            return completion[-1].get("content", "")
        return str(completion)

    def trl_verifiers_bridge(prompts, completions, **kwargs):
        phase = "train" if model.training else "eval"
        batch_size = len(prompts)
        states = []

        for i in range(batch_size):
            raw_text = extract_text(completions[i])
            comp_msg = normalize_messages([{"role": "assistant", "content": raw_text}])
            raw_prompt = prompts[i] if isinstance(prompts[i], list) else [{"role": "user", "content": prompts[i]}]
            prompt_msg = normalize_messages(raw_prompt)

            input_data = {
                "prompt": prompt_msg,
                "example_id": kwargs["example_id"][i],
            }
            if "answer" in kwargs:
                input_data["answer"] = kwargs["answer"][i]
            if "info" in kwargs:
                input_data["info"] = _maybe_json(kwargs["info"][i])

            state = vf.State(input=input_data)
            state["prompt"] = prompt_msg
            state["completion"] = comp_msg
            state["trajectory_id"] = f"trl_{i}_{input_data['example_id']}"
            state["trajectory"] = [{
                "prompt": prompt_msg,
                "completion": comp_msg,
                "response": None,
                "tokens": None,
                "reward": None,
                "advantage": None,
                "is_truncated": False,
                "trajectory_id": state["trajectory_id"],
                "extras": {},
            }]
            state["task"] = input_data.get("info", {}).get("env_id", "openfarm")
            state["metrics"] = {}
            state["error"] = None
            state["is_completed"] = True
            state["is_truncated"] = False
            state["client"] = None
            state["model"] = "unsloth-gemma4"
            state["usage_tracker"] = StateUsageTracker()
            state["tool_defs"] = []
            state["timing"] = {
                "generation_ms": 0.0,
                "scoring_ms": 0.0,
                "total_ms": 0.0,
                "start_time": time.time(),
            }
            states.append(state)

        groups = defaultdict(list)
        for state in states:
            groups[state["input"]["example_id"]].append(state)

        loop = get_or_create_thread_loop()

        async def score_and_cleanup():
            await asyncio.gather(*(vf_env.rubric.score_group(g) for g in groups.values()))
            if hasattr(vf_env.rubric, "cleanup"):
                await asyncio.gather(*(vf_env.rubric.cleanup(s) for s in states))

        loop.run_until_complete(score_and_cleanup())

        for state in states:
            for k, v in state.get("metrics", {}).items():
                try:
                    env_metrics_buffer[f"{phase}/env_metrics/{k}"].append(float(v))
                except (TypeError, ValueError):
                    pass

        return [float(state.get("reward") or 0.0) for state in states]

    trl_verifiers_bridge.__name__ = "verifiers_reward"
    return [trl_verifiers_bridge]

In [6]:
#@title GRPO config
from trl import GRPOConfig, GRPOTrainer

max_completion_length = 768 #@param {type:"integer"}
temperature = 1.0 #@param {type:"number"}
learning_rate = 1e-5 #@param {type:"number"}
rollouts_per_sample = 8 #@param {type:"integer"}
max_steps = 512 #@param {type:"integer"}
save_steps = 256 #@param {type:"integer"}
eval_steps = max(1, int(max_steps * eval_steps_fraction))

training_args = GRPOConfig(
    temperature = temperature,
    learning_rate = learning_rate,
    weight_decay = 0.001,
    warmup_ratio = 0.1,
    lr_scheduler_type = "linear",
    optim = "adamw_8bit",
    logging_steps = 1,
    eval_strategy = "steps",
    eval_steps = eval_steps,
    per_device_eval_batch_size = 1,
    per_device_train_batch_size = 1,
    gradient_accumulation_steps = 2,
    num_generations = rollouts_per_sample,
    max_completion_length = max_completion_length,
    max_steps = max_steps,
    save_steps = save_steps,
    report_to = "wandb" if use_wandb else "none",
    output_dir = "outputs",
    epsilon = 0.2,
    epsilon_high = 0.28,
    delta = 1.5,
    loss_type = "bnpo",
    mask_truncated_completions = True,
    log_completions = True,
)

[transformers] warmup_ratio is deprecated and will be removed in v5.2. Use `warmup_steps` instead.


Unsloth: We now expect `per_device_train_batch_size` * `gradient_accumulation_steps` * `world_size` to be a multiple of `num_generations`.
We will change the batch size of 1 to the `num_generations` of 8


In [ ]:
#@title Show current memory stats
gpu_stats = torch.cuda.get_device_properties(0)
start_gpu_memory = round(torch.cuda.max_memory_reserved() / 1024 / 1024 / 1024, 3)
max_memory = round(gpu_stats.total_memory / 1024 / 1024 / 1024, 3)
print(f"GPU = {gpu_stats.name}. Max memory = {max_memory} GB.")
print(f"{start_gpu_memory} GB of memory reserved.")

In [ ]:
#@title Run GRPO training
import types
from transformers.integrations import WandbCallback

trl_reward_funcs = build_trl_reward_funcs(vf_env, model)

# --- THE FIX ---
# Unsloth's dynamic regex rewriter blindly forces PEFT to copy weights into a "ref" adapter.
# This crashes on Gemma 4 because PEFT does not recognize Unsloth's new `Gemma4ClippableLinear` wrapper.
# We monkeypatch both adapter creation AND parameter retrieval to act as a "black hole", safely bypassing it.
original_add_adapter = model.add_adapter
original_get_parameter = model.get_parameter

def patched_add_adapter(self, adapter_name, *args, **kwargs):
    if adapter_name == "ref":
        return
    return original_add_adapter(adapter_name, *args, **kwargs)

class DummyData:
    def copy_(self, other):
        pass # Black hole: absorb the copy operation and do nothing

class DummyParam:
    data = DummyData()

def patched_get_parameter(self, target):
    if ".ref." in target:
        return DummyParam()
    return original_get_parameter(target)

model.add_adapter = types.MethodType(patched_add_adapter, model)
model.get_parameter = types.MethodType(patched_get_parameter, model)
# ---------------

trainer = GRPOTrainer(
    model = model,
    processing_class = tokenizer,
    reward_funcs = trl_reward_funcs,
    args = training_args,
    train_dataset = train_dataset,
    eval_dataset = eval_dataset,
    callbacks = [VerifiersMetricsCallback()],
)

# --- RESTORE ORIGINAL METHODS ---
model.add_adapter = original_add_adapter
model.get_parameter = original_get_parameter
# --------------------------------

wandb_cb = next((cb for cb in trainer.callback_handler.callbacks if isinstance(cb, WandbCallback)), None)
if wandb_cb:
    trainer.callback_handler.callbacks.remove(wandb_cb)
    trainer.callback_handler.callbacks.append(wandb_cb)

if run_eval_before_training:
    print("Running baseline eval before training...")
    baseline_metrics = trainer.evaluate(metric_key_prefix="eval_baseline")
    print("Baseline eval:", baseline_metrics)

trainer_stats = trainer.train()

if run_eval_after_training:
    print("Running final eval after training...")
    final_metrics = trainer.evaluate(metric_key_prefix="eval_final")
    print("Final eval:", final_metrics)


[transformers] The tokenizer has new PAD/BOS/EOS tokens that differ from the model config and generation config. The model config and generation config were aligned accordingly, being updated with the tokenizer's values. Updated tokens: {'bos_token_id': 2}.
[transformers] ==((====))==  Unsloth - 2x faster free finetuning | Num GPUs used = 1
   \\   /|    Num examples = 228 | Num Epochs = 5 | Total steps = 512
O^O/ \_/ \    Batch size per device = 8 | Gradient accumulation steps = 2
\        /    Data Parallel GPUs = 1 | Total batch size (8 x 2 x 1) = 16
 "-____-"     Trainable parameters = 59,719,680 of 5,164,017,184 (1.16% trained)
wandb: [wandb.login()] Loaded credentials for https://api.wandb.ai from /root/.netrc.
wandb: Currently logged in as: oliveirabruno-swe (bruno0l1veira) to https://api.wandb.ai. Use `wandb login --relogin` to force relogin


wandb: Detected [anthropic, mcp, openai, agents, verifiers] in use.
wandb: Use W&B Weave for improved LLM call tracing. Install Weave with `pip install weave` then add `import weave` to the top of your script.
wandb: For more information, check out the docs at: https://weave-docs.wandb.ai
[transformers] Passing `generation_config` together with generation-related arguments=({'pad_token_id'}) is deprecated and will be removed in future versions. Please pass either a `generation_config` object OR all generation parameters explicitly, but not both.
[transformers] Caching is incompatible with gradient checkpointing in Gemma4TextDecoderLayer. Setting `past_key_values=None`.


Unsloth: Will smartly offload gradients to save VRAM!
Unsloth: Double buffering enabled (parallel H2D + compute) for backward pass.


Step,Training Loss,reward,reward_std,completions / mean_length,completions / min_length,completions / max_length,completions / clipped_ratio,completions / mean_terminated_length,completions / min_terminated_length,completions / max_terminated_length,kl,rewards / verifiers_reward / mean,rewards / verifiers_reward / std
1,-0.091148,0.875000,0.470319,453.250000,184.000000,580.000000,0.000000,453.250000,184.000000,580.000000,0.000000,0.875000,0.470319
2,0.017078,0.372500,0.412529,306.687500,1.000000,425.000000,0.000000,306.687500,1.000000,425.000000,0.000067,0.372500,0.412529
3,-0.260232,0.660000,0.559810,163.250000,1.000000,314.000000,0.000000,163.250000,1.000000,314.000000,0.000033,0.660000,0.559810
4,-0.026785,0.195000,0.013663,393.687500,256.000000,549.000000,0.000000,393.687500,256.000000,549.000000,0.000021,0.195000,0.013663
5,0.012500,0.685000,0.532040,270.187500,193.000000,443.000000,0.000000,270.187500,193.000000,443.000000,0.000012,0.685000,0.532040
6,0.008151,0.570000,0.493694,279.687500,202.000000,419.000000,0.000000,279.687500,202.000000,419.000000,0.000015,0.570000,0.493694
7,-0.261664,0.170000,0.055618,254.625000,1.000000,508.000000,0.000000,254.625000,1.000000,508.000000,0.000029,0.170000,0.055618
8,-0.063235,0.262500,0.250000,357.375000,172.000000,517.000000,0.000000,357.375000,172.000000,517.000000,0.000020,0.262500,0.250000
9,-0.384571,0.650000,0.569163,193.687500,1.000000,484.000000,0.000000,193.687500,1.000000,484.000000,0.000667,0.650000,0.569163
10,0.050929,0.197500,0.010000,396.625000,204.000000,699.000000,0.000000,396.625000,204.000000,699.000000,0.000027,0.197500,0.010000


╭──────────────────────────────────────────────────── Step 1 ─────────────────────────────────────────────────────╮
│ ┏━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━┓ │
│ ┃ Prompt                               ┃ Completion                            ┃ verifiers_reward ┃ Advantage ┃ │
│ ┡━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━┩ │
│ │ system                               │ >`                                    │             1.16 │     -0.72 │ │
│ │ You are an expert veterinary AI.     │ <explanation>                         │                  │           │ │
│ │ user                                 │ [reasoning]The patient is an elderly  │                  │           │ │
│ │ [SPECIES CLASS]                      │ human in an advanced dementia         │                  │           │ │
│ │ Human                                │ setting, unable to communicate        │                  │           │ │
│ │                                      │ verbally, invalidating self-reports   │                  │           │ │
│ │ [SUBJECT]                            │ regarding pain. The visual cues—knees │                  │           │ │
│ │ Human                                │ pulled to the chest, clenched fists,  │                  │           │ │
│ │                                      │ prominent brow-lowering, and raised,  │                  │           │ │
│ │ [CONTEXT]                            │ tightened cheeks—are classic          │                  │           │ │
│ │ Elderly Care Facility, patient       │ indicators of significant physical    │                  │           │ │
│ │ suffers from advanced progressive    │ distress or acute negative affect.    │                  │           │ │
│ │ dementia and is unable to            │ The posture (drawing knees to the     │                  │           │ │
│ │ communicate verbally.                │ chest) suggests self-soothing,        │                  │           │ │
│ │                                      │ guarding, or protective behavior,     │                  │           │ │
│ │ [VISUAL CUES]                        │ often associated with pain or         │                  │           │ │
│ │ Patient has their knees pulled to    │ fear/anxiety. The facial expression   │                  │           │ │
│ │ their chest, fists clenched, and     │ (brow-lowering and tightened cheeks)  │                  │           │ │
│ │ exhibits prominent brow-lowering     │ suggests grimacing or tension. Given  │                  │           │ │
│ │ alongside raised, tightened cheeks.  │ the context that direct evaluation of │                  │           │ │
│ │                                      │ pain is unreliable, the most direct   │                  │           │ │
│ │ [FARM MANAGER ASSESSMENT/EXTERNAL    │ interpretation of these somatic and   │                  │           │ │
│ │ CONTEXT]                             │ facial expressions points toward an   │                  │           │ │
│ │ The patient cannot comprehend or     │ underlying negative experience, most  │                  │           │ │
│ │ respond to simple direct evaluations │ likely pain or significant distress.  │                  │           │ │
│ │ regarding pain presence, rendering   │ Therefore, the state is classified as │                  │           │ │
│ │ self-reports invalid.                │ Negative_Nociceptive (indicating      │                  │           │ │
│ │                                      │ pain) or Negative_Affective           │                  │           │ │
│ │ [TASK]                               │ (indicating distress/fear/anxiety).   │                  │           │ │
│ │ Based on the visual cues and context │ Since the cues are highly indicative  │                  │           │ │
│ │ provided, analyze the animal's       │ of acute phys

...

╭──────────────────────────────────────────────────── Step 14 ────────────────────────────────────────────────────╮
│ ┏━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━┓ │
│ ┃ Prompt                               ┃ Completion                            ┃ verifiers_reward ┃ Advantage ┃ │
│ ┡━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━┩ │
│ │ system                               │ <explanation>                         │             1.20 │      0.00 │ │
│ │ You are an expert veterinary AI      │ [reasoning]                           │                  │           │ │
│ │ analyzing canine clinical metadata.  │ The clinical history strongly         │                  │           │ │
│ │ Based on the provided demographic    │ indicates a presence of pain and      │                  │           │ │
│ │ and clinical history, assess the     │ distress, which is the core component │                  │           │ │
│ │ dog's affective pain state.          │ of affective pain. Key indicators     │                  │           │ │
│ │ user                                 │ include:                              │                  │           │ │
│ │ Review the following clinical        │ 1. **Behavioral signs of pain:** Nala │                  │           │ │
│ │ metadata for a canine patient.       │ "always cried," "had pain in her      │                  │           │ │
│ │                                      │ neck," and "was afraid when touched"  │                  │           │ │
│ │ [CLINICAL CONTEXT]                   │ during the week of May 20th.          │                  │           │ │
│ │ - Species: dog                       │ 2. **Pain-related behaviors:** Waking │                  │           │ │
│ │ - Breed: Yorkshire Terrier           │ up with pain and crying during sleep. │                  │           │ │
│ │ - Sex: f                             │ 3. **Objective signs of distress:**   │                  │           │ │
│ │ - Neuter status: not neutered        │ Shaking and panting on May 25th.      │                  │           │ │
│ │ - Primary diagnosis: Antlantoaxial   │ 4. **Response to treatment:** The     │                  │           │ │
│ │ instability                          │ initial pain medications (Novalgin,   │                  │           │ │
│ │ - Medical history: Nala was          │ CBD) provided "no improvement,"       │                  │           │ │
│ │ presented on the 31 May due to neck  │ necessitating further intervention    │                  │           │ │
│ │ pain and apathy. The week of 20th    │ (Bupaq and Metacam). The subsequent   │                  │           │ │
│ │ May Nala always cried, had pain in   │ worsening on May 31st suggests        │                  │           │ │
│ │ her neck, she was afraid when        │ ongoing, unresolved pain.             │                  │           │ │
│ │ touched. When she slept sometimes    │ 5. **Apathy:** The history notes she  │                  │           │ │
│ │ she waked up with pain and she       │ has been "apathetic since her heat,"  │                  │           │ │
│ │ cried. On 25.05 Nala went to the     │ which can be a sign of chronic pain   │                  │           │ │
│ │ private vet because she was shaking  │ or systemic distress.                 │                  │           │ │
│ │ and panting more. The privatew vet   │                                       │                  │           │ │
│ │ gave Novalgin (CRP increased) and    │ Given the persistent crying, fear,    │                  │           │ │
│ │ stomach protector without            │ physical signs of pain, and the       │                  │           │ │
│ │ improvement. On 27.05 back to the    │ failure of initial management to      │                  │           │ │
│ │ private vet because no improvement,  │ resolve the s

╭──────────────────────────────────────────────────── Step 15 ────────────────────────────────────────────────────╮
│ ┏━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━┓ │
│ ┃ Prompt                               ┃ Completion                            ┃ verifiers_reward ┃ Advantage ┃ │
│ ┡━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━┩ │
│ │ system                               │                                       │             0.20 │      0.54 │ │
│ │ You are an expert veterinary AI.     │ <explanation>                         │                  │           │ │
│ │ user                                 │ [reasoning]                           │                  │           │ │
│ │ [SPECIES CLASS]                      │ The visual cues describe a donkey     │                  │           │ │
│ │ Donkey                               │ exhibiting a "rigid stance," being    │                  │           │ │
│ │                                      │ "completely motionless in the center  │                  │           │ │
│ │ [SUBJECT]                            │ of the trailer," and showing a        │                  │           │ │
│ │ Donkey                               │ "reluctance to move its legs." This   │                  │           │ │
│ │                                      │ presentation is assessed against the  │                  │           │ │
│ │ [CONTEXT]                            │ external context provided by the farm │                  │           │ │
│ │ A donkey has just been loaded into a │ manager assessment, which explicitly  │                  │           │ │
│ │ highly unfamiliar and noisy          │ states that the donkey is *not*       │                  │           │ │
│ │ transport trailer surrounded by      │ pacing, restless, rolling, or         │                  │           │ │
│ │ predatory-looking strays.            │ demonstrating physical agitation      │                  │           │ │
│ │                                      │ typical of equine distress.           │                  │           │ │
│ │ [VISUAL CUES]                        │                                       │                  │           │ │
│ │ The donkey exhibits a rigid stance,  │ The farm manager assessment           │                  │           │ │
│ │ is completely motionless in the      │ interprets the motionless state as a  │                  │           │ │
│ │ center of the trailer, and           │ "calm, neutral behavioral baseline."  │                  │           │ │
│ │ demonstrates a reluctance to move    │                                       │                  │           │ │
│ │ its legs.                            │ In the absence of overt signs of pain │                  │           │ │
│ │                                      │ (e.g., vocalization, trembling,       │                  │           │ │
│ │ [FARM MANAGER ASSESSMENT/EXTERNAL    │ muscle tension indicative of severe   │                  │           │ │
│ │ CONTEXT]                             │ distress, attempts to flee, or active │                  │           │ │
│ │ Because the donkey is not pacing,    │ struggling), and given the manager's  │                  │           │ │
│ │ restless, rolling, or demonstrating  │ explicit assessment of a neutral      │                  │           │ │
│ │ physical agitation typical of equine │ baseline, the most appropriate        │                  │           │ │
│ │ distress, its motionless state       │ classification is one that reflects a │                  │           │ │
│ │ indicates a calm, neutral behavioral │ state of rest or calm, rather than    │                  │           │ │
│ │ baseline.                            │ active distress or positive           │                  │           │ │
│ │                                      │ well-being.  

╭──────────────────────────────────────────────────── Step 16 ────────────────────────────────────────────────────╮
│ ┏━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━┓ │
│ ┃ Prompt                               ┃ Completion                            ┃ verifiers_reward ┃ Advantage ┃ │
│ ┡━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━┩ │
│ │ system                               │ <explanation>                         │             1.20 │      0.00 │ │
│ │ You are an expert veterinary AI      │ [reasoning]                           │                  │           │ │
│ │ analyzing canine clinical metadata.  │ The clinical metadata describes a     │                  │           │ │
│ │ Based on the provided demographic    │ female Golden Retriever with a        │                  │           │ │
│ │ and clinical history, assess the     │ confirmed ectopic ureter diagnosis    │                  │           │ │
│ │ dog's affective pain state.          │ and a history of urinary              │                  │           │ │
│ │ user                                 │ incontinence. A recent, treated       │                  │           │ │
│ │ Review the following clinical        │ urinary tract infection (UTI) with    │                  │           │ │
│ │ metadata for a canine patient.       │ *Staphylococcus pseudintermedius*     │                  │           │ │
│ │                                      │ occurred on 05/09/2024, for which she │                  │           │ │
│ │ [CLINICAL CONTEXT]                   │ has been successfully treated.        │                  │           │ │
│ │ - Species: dog                       │ Crucially, the description states     │                  │           │ │
│ │ - Breed: golden retriever            │ that "Olly is otherwise doing very    │                  │           │ │
│ │ - Sex: female                        │ well, she is fit and active and has a │                  │           │ │
│ │ - Neuter status: not neutered        │ good appetite. Vomiting or diarrhea   │                  │           │ │
│ │ - Primary diagnosis: Ectopic ureter  │ have never occurred." This indicates  │                  │           │ │
│ │ - Medical history: Olly has had      │ that the patient is currently         │                  │           │ │
│ │ urinary incontinence since           │ symptom-free, has a good general      │                  │           │ │
│ │ puppyhood. There is no pollakisuria, │ physical condition, and is not        │                  │           │ │
│ │ stranguria or haematuria. CT and     │ exhibiting overt signs of distress    │                  │           │ │
│ │ cystoscopy confirmed the suspected   │ (such as pain behaviors, lethargy, or │                  │           │ │
│ │ diagnosis of ectopic ureters. The    │ anorexia). Since the patient is "fit  │                  │           │ │
│ │ left ureter is intramurally ectopic  │ and active" and has a "good           │                  │           │ │
│ │ (1.5 cm). The right ureter opens     │ appetite," there is no indication of  │                  │           │ │
│ │ into the bladder neck, which is also │ current affective pain or significant │                  │           │ │
│ │ an abnormal position (normally it    │ distress related to her underlying    │                  │           │ │
│ │ should open about 2 cm inside the    │ condition or recent illness.          │                  │           │ │
│ │ bladder). This could also contribute │ Therefore, the affective state is     │                  │           │ │
│ │ to Olly's incontinence. In addition, │ best classified as neutral resting,   │                  │           │ │
│ │ a urinary tract infection with       │ as she is well and stable             │                  │           │ │
│ │ Staphylococcus pseudintermedius was  │ pre-surgery. 

╭──────────────────────────────────────────────────── Step 17 ────────────────────────────────────────────────────╮
│ ┏━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━┓ │
│ ┃ Prompt                               ┃ Completion                            ┃ verifiers_reward ┃ Advantage ┃ │
│ ┡━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━┩ │
│ │ system                               │                                       │             0.20 │      0.35 │ │
│ │ You are an expert veterinary AI.     │ <explanation>                         │                  │           │ │
│ │ user                                 │ [reasoning]                           │                  │           │ │
│ │ [SPECIES CLASS]                      │ The visual cues provided—widened eyes │                  │           │ │
│ │ Horse                                │ with exposed sclera (scleral show)    │                  │           │ │
│ │                                      │ and overtly flared nostrils—are       │                  │           │ │
│ │ [SUBJECT]                            │ specifically noted by the external    │                  │           │ │
│ │ Equus caballus                       │ context as components associated with │                  │           │ │
│ │                                      │ the "Equine Pain Face," which is an   │                  │           │ │
│ │ [CONTEXT]                            │ indicator of sharp, acute pain. The   │                  │           │ │
│ │ The adult horse is being loaded into │ context further establishes a         │                  │           │ │
│ │ a restrictive transport trailer,     │ high-stress, novel environment        │                  │           │ │
│ │ characterized as a high-stress,      │ involving a restrictive transport     │                  │           │ │
│ │ novel environment with loud metallic │ trailer and loud metallic noises,     │                  │           │ │
│ │ noises.                              │ which are significant stressors for a │                  │           │ │
│ │                                      │ horse.                                │                  │           │ │
│ │ [VISUAL CUES]                        │                                       │                  │           │ │
│ │ The horse is holding an alert,       │ The combination of these              │                  │           │ │
│ │ hyper-responsive posture. Its eyes   │ physiological signs strongly suggests │                  │           │ │
│ │ are noticeably widened with the      │ an active, intense negative           │                  │           │ │
│ │ sclera clearly exposed all the way   │ experience, specifically pain.        │                  │           │ │
│ │ around the iris, and its nostrils    │                                       │                  │           │ │
│ │ are overtly flared.                  │ Biological confounders or distractor  │                  │           │ │
│ │                                      │ information are minimal here. The     │                  │           │ │
│ │ [FARM MANAGER ASSESSMENT/EXTERNAL    │ cues are highly specific indicators   │                  │           │ │
│ │ CONTEXT]                             │ of acute nociception (pain response). │                  │           │ │
│ │ Strained, dilated nostrils and an    │ While stress (Negative_Affective) can │                  │           │ │
│ │ altered eye appearance with exposed  │ cause changes in the face, the        │                  │           │ │
│ │ sclera are components associated     │ explicit link to the "Pain Face"      │                  │           │ │
│ │ with the Equine Pain Face when       │ morphology points toward a direct     │                  │           │ │
│ │ identifying sharp, acute pain.       │ nociceptive i

╭──────────────────────────────────────────────────── Step 18 ────────────────────────────────────────────────────╮
│ ┏━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━━━━━━━━┳━━━━━━━━━━━┓ │
│ ┃ Prompt                               ┃ Completion                            ┃ verifiers_reward ┃ Advantage ┃ │
│ ┡━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━━━━━━━━╇━━━━━━━━━━━┩ │
│ │ system                               │                                       │             0.20 │      0.54 │ │
│ │ You are an expert veterinary AI.     │ <explanation>                         │                  │           │ │
│ │ user                                 │ [reasoning]                           │                  │           │ │
│ │ [SPECIES CLASS]                      │ The visual cue is a goat standing     │                  │           │ │
│ │ Goat                                 │ rigidly with both ears pinned         │                  │           │ │
│ │                                      │ backwards and flattened completely    │                  │           │ │
│ │ [SUBJECT]                            │ against the skull. In ungulates, ear  │                  │           │ │
│ │ Goat                                 │ position is a key indicator of        │                  │           │ │
│ │                                      │ affective state, often reflecting     │                  │           │ │
│ │ [CONTEXT]                            │ fear, pain, or anxiety.               │                  │           │ │
│ │ An adult meat goat is being observed │                                       │                  │           │ │
│ │ post-operatively from a remote       │ However, the context provides a       │                  │           │ │
│ │ digital camera.                      │ critical confounder: the subject is   │                  │           │ │
│ │                                      │ an *adult meat goat*, and the farm    │                  │           │ │
│ │ [VISUAL CUES]                        │ manager assessment explicitly states  │                  │           │ │
│ │ The goat is standing rigidly. Both   │ that due to age, the muscles          │                  │           │ │
│ │ ears are pinned backwards and        │ associated with the scutiform         │                  │           │ │
│ │ flattened completely against the     │ cartilage might be less prominent,    │                  │           │ │
│ │ skull.                               │ meaning the pinned ears cannot be     │                  │           │ │
│ │                                      │ reliably scored as an action unit for │                  │           │ │
│ │ [FARM MANAGER ASSESSMENT/EXTERNAL    │ pain evaluation. This suggests that   │                  │           │ │
│ │ CONTEXT]                             │ relying solely on the ear position    │                  │           │ │
│ │ Because the subject is a mature      │ for a definitive pain assessment      │                  │           │ │
│ │ adult, muscles pertaining to the     │ might be unreliable.                  │                  │           │ │
│ │ scutiform cartilage could in time    │                                       │                  │           │ │
│ │ become less prominent and reduce the │ The posture is rigid and the ears are │                  │           │ │
│ │ possibility of ear movement.         │ maximally flattened, which *suggests* │                  │           │ │
│ │ Therefore, the pinned ears cannot be │ a negative state (pain or fear).      │                  │           │ │
│ │ reliably scored as an action unit    │ However, the assessment explicitly    │                  │           │ │
│ │ for evaluating pain.                 │ guards against interpreting this as a │                  │           │ │
│ │                                      │ reliable pain

In [ ]:
#@title Show final memory and time stats
used_memory = round(torch.cuda.max_memory_reserved() / 1024 / 1024 / 1024, 3)
used_memory_for_lora = round(used_memory - start_gpu_memory, 3)
used_percentage = round(used_memory / max_memory * 100, 3)
lora_percentage = round(used_memory_for_lora / max_memory * 100, 3)
print(f"{trainer_stats.metrics["train_runtime"]} seconds used for training.")
print(f"{round(trainer_stats.metrics["train_runtime"]/60, 2)} minutes used for training.")
print(f"Peak reserved memory = {used_memory} GB.")
print(f"Peak reserved memory for training = {used_memory_for_lora} GB.")
print(f"Peak reserved memory % of max memory = {used_percentage} %.")
print(f"Peak reserved memory for training % of max memory = {lora_percentage} %.")

## Inference Smoke Test

In [ ]:
#@title Quick post-training generation smoke test
sample = train_dataset[0]
messages = sample["prompt"]
inputs = tokenizer.apply_chat_template(
    messages,
    add_generation_prompt = True,
    return_tensors = "pt",
    tokenize = True,
    return_dict = True,
).to("cuda")

from transformers import TextStreamer
streamer = TextStreamer(tokenizer, skip_prompt = True)
_ = model.generate(
    **inputs,
    max_new_tokens = 256,
    temperature = 1.0,
    top_p = 0.95,
    top_k = 64,
    streamer = streamer,
)
print("Gold answer:", sample["answer"])
print("Route:", route_name(sample["info"]))

## Save

In [ ]:
#@title Save LoRA locally and optionally push to Hugging Face
output_lora_dir = "openfarm_gemma4_text_rl_lora" #@param {type:"string"}
push_to_hub = False #@param {type:"boolean"}
hf_lora_repo = "YOUR_USERNAME/openfarm-gemma4-text-rl-lora" #@param {type:"string"}

model.save_pretrained(output_lora_dir)
tokenizer.save_pretrained(output_lora_dir)
print("Saved LoRA to", output_lora_dir)

if push_to_hub:
    model.push_to_hub(hf_lora_repo, token = os.environ.get("HF_TOKEN"))
    tokenizer.push_to_hub(hf_lora_repo, token = os.environ.get("HF_TOKEN"))
    print("Pushed LoRA to", hf_lora_repo)

## Suggested video caption

"OpenFARM environments are not just benchmarks. They are trainable research tasks: here, Gemma 4 learns from a Prime/Verifiers EnvGroup spanning animal-welfare reasoning, canine clinical pain triage, and bioacoustic metadata classification, with Unsloth GRPO providing the low-cost training loop."